# **Difusión y Tractografía en Gliomas**


# **1. Introducción y Principios Físicos**

El DTI (*Diffusion Tensor Imaging*) es una técnica de resonancia magnética que mide el movimiento microscópico de las moléculas de agua.

**El Fenómeno de la Difusión**

En el cerebro, el agua no se mueve libremente en todas las direcciones.

* **Difusión Isotrópica (a):** En el líquido cefalorraquídeo, el agua se mueve igual en todas direcciones (como una esfera).

* **Difusión Anisótropa (b):** En la sustancia blanca, las vainas de mielina y los axones actúan como barreras. El agua se difunde más fácilmente a lo largo del axón que a través de él.


<img src="https://raw.githubusercontent.com/pamelaFranco/workshop_glioma/main/Figuras/difusion_tipos.svg" width="700" height="500" style="object-fit: contain;">
---

**El Tensor de Difusión:**

Para representar este movimiento en 3D, usamos un Tensor (una matriz matemática de 3x3).

$$D = \begin{pmatrix} D_{xx} & D_{xy} & D_{xz} \\ D_{yx} & D_{yy} & D_{yz} \\ D_{zx} & D_{zy} & D_{zz} \end{pmatrix}$$

Este tensor se puede visualizar como un elipsoide. Al diagonalizar esta matriz, obtenemos los autovalores (eigenvalues) $\lambda_1, \lambda_2, \lambda_3$, que representan la magnitud de la difusión en las tres direcciones principales del espacio:

* **Eigenvalues ($\lambda_1, \lambda_2, \lambda_3$)**: Indican la magnitud de la difusión.

* **Eigenvectors**: Indican la dirección de los ejes del elipsoide. El vector principal ($V_1$) nos dice hacia dónde va el tracto nervioso.


**Mapas de Difusión**

**1. Difusividad Media (MD):** Representa el promedio de la difusión en un vóxel, independientemente de la dirección. En gliomas, un aumento de MD suele indicar edema o ruptura de barreras.
$$\text{MD} = \frac{\lambda_1 + \lambda_2 + \lambda_3}{3}$$

**2. Fracción de Anisotropía (FA):** Es el parámetro más usado. Mide qué tan "estirado" es el elipsoide. Varía entre 0 (esfera perfecta, difusión isotrópica como el LCR) y 1 (difusión en una sola línea, como un axón perfecto).$$\text{FA} = \sqrt{\frac{3}{2}} \frac{\sqrt{(\lambda_1 - \text{MD})^2 + (\lambda_2 - \text{MD})^2 + (\lambda_3 - \text{MD})^2}}{\sqrt{\lambda_1^2 + \lambda_2^2 + \lambda_3^2}}$$

**3. Difusividad Axial (AD) y Radial (RD):** Estos mapas son muy útiles para diferenciar tipos de daño axonal:

  * **Axial (AD):** Difusión paralela al tracto ($\lambda_1$). Su caída indica daño en el axón mismo.

$$\text{AD} = \lambda_1$$

  * **Radial (RD):** Promedio de la difusión perpendicular al tracto. Su aumento suele indicar desmielinización.

$$\text{RD} = \frac{\lambda_2 + \lambda_3}{2}$$

# **2. Configuración del Entorno (Código)**
Este bloque instala las librerías necesarias (como `Dipy` para imágenes de difusión o `Plotly` para gráficos interactivos).

In [ ]:
# Instalación silenciosa de las librerías necesarias para neuroimagen
!pip install -q nilearn nibabel dipy
!pip install -q dipy fury
print("Librerías instaladas correctamente.")


   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 10.6/10.6 MB 60.1 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 10.7/10.7 MB 69.5 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 55.9/55.9 kB 5.0 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 92.0/92.0 kB 7.2 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 596.0/596.0 kB 12.5 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 92.2/92.2 MB 9.4 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 51.0/51.0 kB 3.5 MB/s eta 0:00:00
Librerías instaladas correctamente.


# **3. Carga de Datos**

Este bloque carga los datos del paciente (imágenes médicas en formato NIfTI).

In [ ]:
import nibabel as nib
import os
from nilearn import plotting

# URL base correcta del repositorio
base_url = "https://raw.githubusercontent.com/pamelaFranco/workshop_glioma/main/Dataset/DATOS_ANONIMIZADOS_WORKSHOP/"

# Nombres de los archivos en GitHub
files = {
    "fa": "Sujeto01_s08.src.gz.dti.fib.gz.fa.nii.gz",
    "md": "Sujeto01_s08.src.gz.dti.fib.gz.md.nii.gz",
    "rd": "Sujeto01_s08.src.gz.dti.fib.gz.rd.nii.gz",
    "ad": "Sujeto01_s08.src.gz.dti.fib.gz.ad.nii.gz",
    "anat": "Sujeto01_Ax_FSPGR_3D_N.nii.gz"
}

# Descarga de archivos
for key in files:
    file_name = files[key]
    url = base_url + file_name
    !wget -q --show-progress {url} -O {file_name}

# Carga de objetos
try:
    fa_img = nib.load(files["fa"])
    md_img = nib.load(files["md"])
    rd_img = nib.load(files["rd"])
    ad_img = nib.load(files["ad"])
    anat_img = nib.load(files["anat"])
    print("¡Todos los archivos cargados exitosamente!")
except Exception as e:
    print(f"Error al cargar: {e}")

Sujeto01_s08.src.gz 100%[===================>] 984.74K  --.-KB/s    in 0.05s   
Sujeto01_s08.src.gz 100%[===================>] 966.55K  --.-KB/s    in 0.05s   
Sujeto01_s08.src.gz 100%[===================>] 973.99K  --.-KB/s    in 0.05s   
Sujeto01_s08.src.gz 100%[===================>] 972.65K  --.-KB/s    in 0.05s   
Sujeto01_Ax_FSPGR_3 100%[===================>]   7.69M  --.-KB/s    in 0.09s   
¡Todos los archivos cargados exitosamente!


# **4. Panel de Control Interactivo: Explorador de Tensores de Difusión**

**¿Qué hace este código?**

Este código crea una interfaz visual que permite navegar por el cerebro del paciente sin necesidad de escribir más líneas de comandos. Funciona en tres pasos simples:

* **La Biblioteca de Imágenes (`mapas_dict`):** El código organiza los resultados que calculamos anteriormente (FA, MD, RD, AD) en un "archivo" o diccionario. Cuando tú eliges un nombre (por ejemplo, 'FA'), el programa sabe exactamente qué imagen digital debe ir a buscar.

* **La Función de Visualización (`explorar_mapas`)**: Es como un proyector de diapositivas. Recibe dos instrucciones:

 * ¿Qué mapa quieres ver?

 * ¿En qué altura del cerebro quieres mirar? (el corte `slice_z`).
Usando una herramienta llamada nilearn, toma la imagen médica y la "corta" virtualmente para mostrártela en la pantalla.

* **El Panel de Control (`widgets.interact`):** Esta es la parte mágica. Crea los controles físicos en tu pantalla:

 * **Un Deslizador (Slider):** Para moverte de abajo hacia arriba a través del cerebro.

 * **Un Menú Desplegable:** Para cambiar instantáneamente entre diferentes tipos de análisis (como cambiar el filtro de una fotografía).


In [ ]:
import ipywidgets as widgets
from nilearn import plotting
import matplotlib.pyplot as plt

def explorar_mapas(slice_z, mapa):
    # Diccionario para seleccionar la imagen correcta
    mapas_dict = {
        'FA': fa_img,
        'MD': md_img,
        'RD': rd_img,
        'AD': ad_img
    }

    img = mapas_dict[mapa]

    # Visualización
    plotting.plot_anat(img, display_mode='z', cut_coords=[slice_z],
                       title=f"Mapa de {mapa} - Corte {slice_z}")
    plt.show()

# ESTO ES LO QUE TE FALTA PARA QUE SE MUESTRE:
widgets.interact(explorar_mapas,
                 slice_z=widgets.IntSlider(min=-20, max=50, step=1, value=0),
                 mapa=['FA', 'MD', 'RD', 'AD'])

interactive(children=(IntSlider(value=0, description='slice_z', max=50, min=-20), Dropdown(description='mapa',…

<function __main__.explorar_mapas(slice_z, mapa)>

# **5. Tractografía Global**


Este bloque de código es el encargado de crear la maqueta 3D interactiva del paciente. En lugar de ver "rebanadas" de una en una, aquí estamos unificando todas las piezas del rompecabezas anatómico en un solo espacio tridimensional.

A grandes rasgos, el código realiza tres tareas fundamentales:

**1. Reconstrucción de Superficies (Capa Exterior y Tumor)**

El código utiliza una técnica llamada Marching Cubes. Imagina que el escáner médico es una nube de puntos; este algoritmo actúa como un "envoltorio" que rodea esos puntos para crear una superficie sólida.

  * **La Corteza:** Se dibuja como una cáscara gris semitransparente que nos sirve de referencia.

  * **El Tumor: **Se reconstruye como una masa de color rojo. Lo más importante aquí es que el código asegura que el tumor aparezca exactamente en su lugar real respecto al resto del cerebro.

**2. Dibujado de las "Carreteras" Cerebrales (Tractografía)**

Aquí es donde visualizamos los cables (axones) que conectan las distintas partes del cerebro:

  * **Filtrado:** Para que la computadora no se bloquee, el código selecciona 1 de cada 20 fibras (es como dibujar las carreteras principales en lugar de cada callejón).

  * **Color por Dirección:** El código asigna colores automáticamente:

     * **Rojo:** Si la fibra va de izquierda a derecha.

     * **Verde:** Si va de adelante hacia atrás.

     * **Azul:** Si va de arriba hacia abajo.

Esto permite ver de un vistazo si el tumor está cortando, empujando o simplemente pasando al lado de un camino neuronal importante.

**3. Alineación en el "Punto Cero"**

Para que la rotación en 3D sea fluida y fácil de manipular con el ratón, el código toma todo el conjunto (cerebro, tumor y fibras) y lo coloca en el centro del visor (coordenadas 0,0,0). Esto evita que la imagen "salte" o se pierda de vista cuando intentas girarla para inspeccionar el tumor desde distintos ángulos.



In [ ]:
import os

# URL base del repositorio de GitHub
base_url = "https://raw.githubusercontent.com/pamelaFranco/workshop_glioma/main/Dataset/DATOS_ANONIMIZADOS_WORKSHOP/"

# Lista completa de archivos necesarios para tu visualización 3D
files_to_download = [
    "Sujeto01_Ax_FSPGR_3D_N.nii.gz",
    "Sujeto01_c1Ax_FSPGR_3D_N.nii.gz",
    "Sujeto01_ROI_tumor_N.nii.gz",
    "Sujeto01_global_tractography.trk",
    "Sujeto01_s08.src.gz.dti.fib.gz.fa.nii.gz"
]

print("Iniciando descarga de archivos...")

for file_name in files_to_download:
    url = base_url + file_name
    # Solo descarga si el archivo no existe ya en Colab
    if not os.path.exists(file_name):
        !wget -q --show-progress {url} -O {file_name}
    else:
        print(f"El archivo {file_name} ya existe.")

print("\n¡Todos los archivos están listos en el entorno de Colab!")

Iniciando descarga de archivos...
El archivo Sujeto01_Ax_FSPGR_3D_N.nii.gz ya existe.
Sujeto01_c1Ax_FSPGR 100%[===================>]   1.34M  --.-KB/s    in 0.06s   
Sujeto01_ROI_tumor_ 100%[===================>]  52.20K  --.-KB/s    in 0.01s   
Sujeto01_global_tra 100%[===================>]  17.82M  --.-KB/s    in 0.1s    
El archivo Sujeto01_s08.src.gz.dti.fib.gz.fa.nii.gz ya existe.

¡Todos los archivos están listos en el entorno de Colab!


In [ ]:
import nibabel as nib
import numpy as np
import plotly.graph_objects as go
from skimage import measure

def get_centered_mesh(nii_path):
    """Carga las máscaras y la tractografía"""
    img = nib.load(nii_path)
    data = img.get_fdata()
    # Marching cubes en espacio de vóxeles
    verts, faces, _, _ = measure.marching_cubes(data, level=0.5)
    # Centramos los vértices restando su propio promedio
    centro = verts.mean(axis=0)
    verts_centered = verts - centro
    return verts_centered, faces

try:
    fig = go.Figure()

    # 1. CARGAR Y CENTRAR MÁSCARAS
    # Centramos la corteza en el origen (0,0,0)
    cortex_v, cortex_f = get_centered_mesh("Sujeto01_c1Ax_FSPGR_3D_N.nii.gz")

    # IMPORTANTE: El tumor debe moverse exactamente lo mismo que la corteza
    # para mantener su posición anatómica relativa.
    nii_ref = nib.load("Sujeto01_c1Ax_FSPGR_3D_N.nii.gz")
    centro_referencia = measure.marching_cubes(nii_ref.get_fdata(), level=0.5)[0].mean(axis=0)

    nii_tumor = nib.load("Sujeto01_ROI_tumor_N.nii.gz")
    tumor_v_raw, tumor_f, _, _ = measure.marching_cubes(nii_tumor.get_fdata(), level=0.5)
    tumor_v = tumor_v_raw - centro_referencia

    # 2. CARGAR Y CENTRAR TRACTOGRAFÍA
    trk = nib.streamlines.load("Sujeto01_global_tractography.trk")
    streamlines = trk.streamlines

    # Calculamos el centro de TODA la tractografía
    all_points = np.vstack(streamlines)
    centro_trk = all_points.mean(axis=0)
    print(f"Centro original TRK: {centro_trk}")

    indices = np.arange(0, len(streamlines), 20)
    for i in indices:
        # Trasladamos cada fibra al origen (0,0,0)
        sl_centered = streamlines[i] - centro_trk

        # Color por dirección
        diff = np.abs(sl_centered[0] - sl_centered[-1])
        norm = np.max(diff) if np.max(diff) > 0 else 1
        color = f'rgb({int(255*diff[0]/norm)}, {int(255*diff[1]/norm)}, {int(255*diff[2]/norm)})'

        fig.add_trace(go.Scatter3d(
            x=sl_centered[:, 0], y=sl_centered[:, 1], z=sl_centered[:, 2],
            mode='lines', line=dict(color=color, width=1.5),
            showlegend=False
        ))

    # 3. MOSTRAR MÁSCARAS CENTRADAS
    fig.add_trace(go.Mesh3d(
        x=cortex_v[:, 0], y=cortex_v[:, 1], z=cortex_v[:, 2],
        i=cortex_f[:, 0], j=cortex_f[:, 1], k=cortex_f[:, 2],
        color='lightgray', opacity=0.1, name='Materia Gris'
    ))

    fig.add_trace(go.Mesh3d(
        x=tumor_v[:, 0], y=tumor_v[:, 1], z=tumor_v[:, 2],
        i=tumor_f[:, 0], j=tumor_f[:, 1], k=tumor_f[:, 2],
        color='red', opacity=0.5, name='Tumor'
    ))

    fig.update_layout(
        template="plotly_dark",
        scene=dict(
            xaxis=dict(title="X", range=[-100, 100]),
            yaxis=dict(title="Y", range=[-100, 100]),
            zaxis=dict(title="Z", range=[-100, 100]),
            aspectmode='cube'
        ),
        title="Sincronización Total: Centrado en (0,0,0)"
    )

    print("Todo ha sido trasladado al origen común.")
    fig.show()

except Exception as e:
    print(f"Error: {e}")

Centro original TRK: [124.16258  102.89733   88.499344]
Todo ha sido trasladado al origen común.
